<a href="https://colab.research.google.com/github/kumarmaheshbly-oss/Project-Aura-/blob/main/constellation_station_keeping.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

In [1]:

import numpy as np
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation
from IPython.display import HTML # <-- Ye naya add kiya hai

# ---------- Constants ----------
GM = 3.986e14
R_E = 6371e3
ALT = 700e3
R = R_E + ALT
V = np.sqrt(GM / R)
OMEGA = V / R

# ---------- Constellation ----------
N = 24
dt = 5.0
steps = 300                 # Mobile par smooth chalne ke liye kam kiya hai

slot_angle = np.linspace(0, 2*np.pi, N, endpoint=False)

theta = slot_angle.copy()
omega = np.full(N, OMEGA)

rng = np.random.default_rng(42)
omega *= (1 + rng.normal(0, 5e-6, N))

K = 0.02
DEADBAND = 1e-4
fuel_used = np.zeros(N)

fig, ax = plt.subplots(figsize=(8, 8))
ax.set_aspect('equal')
ax.set_xlim(-1.4*R, 1.4*R)
ax.set_ylim(-1.4*R, 1.4*R)

earth = plt.Circle((0, 0), R_E, color='skyblue', zorder=1)
ax.add_patch(earth)
orbit_line = plt.Circle((0, 0), R, fill=False, ls='--', color='gray', alpha=0.5, zorder=2)
ax.add_patch(orbit_line)

slot_x, slot_y = R*np.cos(slot_angle), R*np.sin(slot_angle)
ax.scatter(slot_x, slot_y, marker='x', c='red', s=40, label='Assigned slots', zorder=3)

sat_pts, = ax.plot([], [], 'o', color='lime', ms=9, label='Satellites', zorder=4)
ring_line, = ax.plot([], [], '-', color='lime', lw=0.5, alpha=0.5, zorder=3)

status_text = ax.text(0.02, 0.98, "", transform=ax.transAxes, va='top', fontsize=9)

ax.legend(loc='upper right', fontsize=8)
ax.set_title("Autonomous Slot-Based Ring — no physical link")

def init():
    return sat_pts, ring_line, status_text

def update(frame):
    global theta, omega, fuel_used

    theta = (theta + omega * dt) % (2*np.pi)
    error = (theta - slot_angle + np.pi) % (2*np.pi) - np.pi
    correction = np.where(np.abs(error) > DEADBAND, -K * error, 0.0)
    theta = (theta + correction) % (2*np.pi)
    fuel_used += np.abs(correction)

    x, y = R*np.cos(theta), R*np.sin(theta)
    sat_pts.set_data(x, y)

    order = np.argsort(theta)
    ring_line.set_data(
        np.append(x[order], x[order][0]),
        np.append(y[order], y[order][0])
    )

    locked = np.sum(np.abs(error) < 0.01)
    status_text.set_text(
        f"Slots locked: {locked}/{N}\n"
        f"Max error: {np.max(np.abs(error))*180/np.pi:.3f}°\n"
        f"Fuel used: {fuel_used.sum():.2f} rad-units"
    )
    return sat_pts, ring_line, status_text

ani = FuncAnimation(fig, update, frames=steps, init_func=init,
                    interval=40, blit=False)

plt.tight_layout()
plt.close() # <-- Ye zaroori hai duplicate plot rokne ke liye

# Colab me animation play karne ke liye ye line:
HTML(ani.to_jshtml())